# GTFS Bus and Rail Stops Map
This notebook will compute the map showing the GTFS LA Metro Bus and Rail stops within the LA County and City of LA Boundary. Because we are graphing with the boundaries, we will formally determine the study area in this notebook as well.

## Import Libraries and Files

In [53]:
from zipfile import ZipFile

import pandas as pd
import geopandas as gpd
import matplotlib.pyplot as plt
import folium

In [3]:
from pathlib import Path
 
raw_dir = Path("../data/raw")
output_dir = Path("../outputs")

print("Raw data folder exists:", raw_dir.exists())
print("Output folder exists:", output_dir.exists())
print("\nFiles in raw data folder:")

for path in sorted(raw_dir.iterdir()):
    print(path.name)

Raw data folder exists: True
Output folder exists: True

Files in raw data folder:
.ipynb_checkpoints
gtfs_bus_2020.zip
gtfs_bus_2026.zip
gtfs_rail_2020.zip
gtfs_rail_2026.zip
tl_2020_06_place.zip
tl_2020_06_tract.zip
tl_2024_06_place.zip
tl_2024_06_tract.zip
tl_2026_06_place.zip
tl_2026_06_tract.zip


In [5]:
# Boundaries
tracts = gpd.read_file("../data/raw/tl_2024_06_tract.zip")
places = gpd.read_file("../data/raw/tl_2024_06_place.zip")

# GTFS Data
feed_path = ...

with ZipFile("../data/raw/gtfs_bus_2026.zip") as feed:
    bus_stops = pd.read_csv(feed.open("stops.txt"))

with ZipFile("../data/raw/gtfs_rail_2026.zip") as feed:
    rail_stops = pd.read_csv(feed.open("stops.txt"))

### Breifly Display Each File

In [11]:
display(bus_stops.head())
display(rail_stops.head())

print(bus_stops.shape)
print(rail_stops.shape)

,stop_id,stop_code,stop_name,stop_desc,stop_lat,stop_lon,stop_url,location_type,parent_station,tpis_name
0,1,1,Paramount / Slauson,NaN,33.973248,-118.113113,NaN,NaN,NaN,NaN
1,3,3,Jefferson / 10th,NaN,34.025471,-118.328402,NaN,NaN,NaN,NaN
2,6,6,120th / Augustus F Hawkins,NaN,33.924696,-118.242222,NaN,NaN,NaN,NaN
3,7,7,120th / Martin Luther King Hospital,NaN,33.924505,-118.240369,NaN,NaN,NaN,NaN
4,12,12,15054 Sherman Way,NaN,34.201075,-118.461953,NaN,NaN,NaN,NaN


,stop_id,stop_code,stop_name,stop_desc,stop_lat,stop_lon,stop_url,location_type,parent_station,tpis_name
0,80101,80101,Downtown Long Beach Station,NaN,33.768071,-118.192921,NaN,0,80101S,Long Bch
1,80101S,80101S,Downtown Long Beach Station,NaN,33.768071,-118.192921,NaN,1,NaN,NaN
2,80101A,80101A,Downtown Long Beach Station - 1st & Pacific En...,NaN,33.768050,-118.193500,NaN,2,80101S,NaN
3,80101B,80101B,Downtown Long Beach Station - 1st & Pine Entrance,NaN,33.768040,-118.192500,NaN,2,80101S,NaN
4,80102,80102,Pacific Ave Station,NaN,33.772258,-118.193700,NaN,0,80102S,Pacific


(11892, 10)
(463, 10)


In [13]:
display(tracts.head())
display(places.head())

print(tracts.shape)
print(places.shape)
print("Tract CRS:", tracts.crs)
print("Place CRS:", places.crs)

,STATEFP,COUNTYFP,TRACTCE,GEOID,GEOIDFQ,NAME,NAMELSAD,MTFCC,FUNCSTAT,ALAND,AWATER,INTPTLAT,INTPTLON,geometry
0,06,001,442700,06001442700,1400000US06001442700,4427,Census Tract 4427,G5020,S,1234016,0,+37.5371513,-122.0081095,"POLYGON ((-122.01721 37.53932, -122.01719 37.5..."
1,06,001,442800,06001442800,1400000US06001442800,4428,Census Tract 4428,G5020,S,1278646,0,+37.5293619,-121.9931002,"POLYGON ((-122.0023 37.52984, -122.00224 37.52..."
2,06,037,204920,06037204920,1400000US06037204920,2049.20,Census Tract 2049.20,G5020,S,909972,0,+34.0175004,-118.1974975,"POLYGON ((-118.20284 34.01966, -118.20283 34.0..."
3,06,037,205110,06037205110,1400000US06037205110,2051.10,Census Tract 2051.10,G5020,S,286962,0,+34.0245059,-118.2142985,"POLYGON ((-118.21964 34.02628, -118.21945 34.0..."
4,06,037,205120,06037205120,1400000US06037205120,2051.20,Census Tract 2051.20,G5020,S,1466242,0,+34.0187542,-118.2117951,"POLYGON ((-118.22023 34.02056, -118.22018 34.0..."


,STATEFP,PLACEFP,PLACENS,GEOID,GEOIDFQ,NAME,NAMELSAD,LSAD,CLASSFP,PCICBSA,MTFCC,FUNCSTAT,ALAND,AWATER,INTPTLAT,INTPTLON,geometry
0,06,14218,02409488,0614218,1600000US0614218,Clovis,Clovis city,25,C1,N,G4110,A,68002602,309836,+36.8278093,-119.6818434,"MULTIPOLYGON (((-119.61479 36.79625, -119.6126..."
1,06,27000,02410546,0627000,1600000US0627000,Fresno,Fresno city,25,C1,Y,G4110,A,300202535,3114247,+36.7826843,-119.7933595,"MULTIPOLYGON (((-119.69999 36.73098, -119.6999..."
2,06,13945,02409479,0613945,1600000US0613945,Clearlake,Clearlake city,25,C1,Y,G4110,A,26235110,1167608,+38.9600452,-122.6332316,"POLYGON ((-122.69949 38.97838, -122.69932 38.9..."
3,06,02112,02409709,0602112,1600000US0602112,Angels,Angels city,25,C1,N,G4110,A,9407811,12740,+38.0710375,-120.5517286,"POLYGON ((-120.57268 38.08597, -120.57269 38.0..."
4,06,01444,02409688,0601444,1600000US0601444,Alturas,Alturas city,25,C1,N,G4110,A,7352926,46987,+41.4891359,-120.5512862,"MULTIPOLYGON (((-120.56009 41.47144, -120.5600..."


(9129, 14)
(1618, 17)
Tract CRS: EPSG:4269
Place CRS: EPSG:4269


## Merge GTFS Stops

In [30]:
# Make a new column to differentiate Bus & Rail Stops
bus_stops["mode"] = "bus"
rail_stops['mode'] = "rail"

# Merge
stops = pd.concat([bus_stops, rail_stops], ignore_index=True)

print(f"# of Bus stops: {len(bus_stops)}, Rail stops: {len(rail_stops)}, Combined: {len(stops)}.")
display(stops.head())

# Select the essential columns
all_stops = stops.copy().loc[:, ["stop_id", "stop_name", "stop_lat", "stop_lon", "mode"]]
all_stops

# of Bus stops: 11892, Rail stops: 463, Combined: 12355.


,stop_id,stop_code,stop_name,stop_desc,stop_lat,stop_lon,stop_url,location_type,parent_station,tpis_name,mode
0,1,1,Paramount / Slauson,NaN,33.973248,-118.113113,NaN,NaN,NaN,NaN,bus
1,3,3,Jefferson / 10th,NaN,34.025471,-118.328402,NaN,NaN,NaN,NaN,bus
2,6,6,120th / Augustus F Hawkins,NaN,33.924696,-118.242222,NaN,NaN,NaN,NaN,bus
3,7,7,120th / Martin Luther King Hospital,NaN,33.924505,-118.240369,NaN,NaN,NaN,NaN,bus
4,12,12,15054 Sherman Way,NaN,34.201075,-118.461953,NaN,NaN,NaN,NaN,bus


,stop_id,stop_name,stop_lat,stop_lon,mode
0,1,Paramount / Slauson,33.973248,-118.113113,bus
1,3,Jefferson / 10th,34.025471,-118.328402,bus
2,6,120th / Augustus F Hawkins,33.924696,-118.242222,bus
3,7,120th / Martin Luther King Hospital,33.924505,-118.240369,bus
4,12,15054 Sherman Way,34.201075,-118.461953,bus
...,...,...,...,...,...
12350,81401S,Grand Ave Arts / Bunker Hill Station,34.054724,-118.251531,rail
12351,81402,Historic Broadway Station,34.052156,-118.246321,rail
12352,81402S,Historic Broadway Station,34.052156,-118.246321,rail
12353,81403,Little Tokyo / Arts District Station,34.048845,-118.238757,rail


For our map, we wouldn't need all columns of this dataframe, instead we would only need geographic location, and their id and names.

## Filter the `places` to only City of LA

In [29]:
# Filter to only the City of LA
la = places.copy()

la_mask = la['NAME'].str.strip() == "Los Angeles"
la = la[la_mask]
la

,STATEFP,PLACEFP,PLACENS,GEOID,GEOIDFQ,NAME,NAMELSAD,LSAD,CLASSFP,PCICBSA,MTFCC,FUNCSTAT,ALAND,AWATER,INTPTLAT,INTPTLON,geometry
138,06,44000,02410877,0644000,1600000US0644000,Los Angeles,Los Angeles city,25,C1,Y,G4110,A,1218641632,80409616,+34.0193936,-118.4108248,"POLYGON ((-118.66818 34.18987, -118.66815 34.1..."


## Inspect the two boundaries

In [41]:
# Extract the City of LA Boundary
city_bound = la.geometry.union_all()

# Check for the tracts that are within and/or intersect the Boundary
intersecting = tracts[tracts.intersects(city_bound)]
within = tracts[tracts.within(city_bound)]

# Also filter out the ones that could be partially in the boundary
partial = intersecting.loc[~intersecting.index.isin(within.index)].copy()

print("Tracts intersecting the city:", len(intersecting))
print("Tracts fully within the city:", len(within))
print("Intersecting but not fully within:", len(partial))

Tracts intersecting the city: 1308
Tracts fully within the city: 1096
Intersecting but not fully within: 212


## Convert GTFS to GeoDataFrame

In [45]:
# Inspect Lat and Lon Ranges
print("Latitude range:")
print(all_stops["stop_lat"].min(), all_stops["stop_lat"].max())

print("Longitude range:")
print(all_stops["stop_lon"].min(), all_stops["stop_lon"].max())

Latitude range:
33.706853 34.326157
Longitude range:
-118.860915 -117.7522


In [48]:
# Convert to GeoDataFrame
stops_gdf = gpd.GeoDataFrame(all_stops, 
                             geometry = gpd.points_from_xy(stops["stop_lon"],stops["stop_lat"]),
                             crs = "EPSG:4269")

# Filter to only stops in City of LA
la_stops_gdf = stops_gdf[stops_gdf.within(city_bound)].copy()

display(la_stops_gdf)
print(f"# of Stops: {len(stops_gdf)}, Stops in LA: {len(la_stops_gdf)}")
print(f"Stops by mode in LA:")
print(la_stops_gdf["mode"].value_counts())

,stop_id,stop_name,stop_lat,stop_lon,mode,geometry
1,3,Jefferson / 10th,34.025471,-118.328402,bus,POINT (-118.3284 34.02547)
4,12,15054 Sherman Way,34.201075,-118.461953,bus,POINT (-118.46195 34.20108)
5,16,Riverside / Los Feliz,34.116932,-118.271486,bus,POINT (-118.27149 34.11693)
7,19,Indiana / Olympic,34.018999,-118.192361,bus,POINT (-118.19236 34.019)
10,31,3rd / Gardner,34.070240,-118.353264,bus,POINT (-118.35326 34.07024)
...,...,...,...,...,...,...
12350,81401S,Grand Ave Arts / Bunker Hill Station,34.054724,-118.251531,rail,POINT (-118.25153 34.05472)
12351,81402,Historic Broadway Station,34.052156,-118.246321,rail,POINT (-118.24632 34.05216)
12352,81402S,Historic Broadway Station,34.052156,-118.246321,rail,POINT (-118.24632 34.05216)
12353,81403,Little Tokyo / Arts District Station,34.048845,-118.238757,rail,POINT (-118.23876 34.04885)


# of Stops: 12355, Stops in LA: 7208
Stops by mode in LA:
mode
bus     6954
rail     254
Name: count, dtype: int64


## Interactive Map: Bus and Rail Stops in the City of Los Angeles

In [73]:
# Use .explore() to create interactive map
## Filter the columns we need
tract_map = intersecting[["GEOID", "NAME", "geometry"]].copy()

# Layer for ALL Census Tract of LA County
m = tract_map.explore(
    color = "grey",
    fillOpacity = 0.25,
    weight = 0.5,
    tooltip = ["GEOID", "NAME"],
    name = "Census tracts",
    tiles = None
)

la.explore(
    m = m,
    color = "black",
    fill = False,
    name = "City of Los Angeles boundary"
)

la_stops_gdf.explore(
    m = m,
    column = "mode",
    color = "blue",
    marker_type = "circle",
    marker_kwds = {"radius": 4},
    tooltip = ["stop_name"],
    name = "Bus/Rail Stop in City of LA"
)

stops_gdf.explore(
    m = m,
    column = "mode",
    color = "blue",
    marker_type = "circle",
    marker_kwds = {"radius": 4},
    tooltip = ["stop_name"],
    name = "All Bus/Rail Stops"
)

# the basemap, kept out of the layer box
folium.TileLayer("Esri.WorldGrayCanvas",control=False,).add_to(m)
folium.LayerControl(collapsed=False).add_to(m)

m